# Pigeon Detection — Dataset Merge + YOLO11n Fine-Tuning
GEN2002Y Project — Auto Pigeon Deterrent System

**Model choice: YOLO11n** — nano variant, chosen for lightweight CPU inference on Raspberry Pi. Slightly better accuracy/speed tradeoff than YOLOv8n at the same size; same Ultralytics API so this notebook stays simple.

**Pipeline:**
1. Install dependencies
2. Pull pigeon datasets from Roboflow (NEA + yolo 1199-image set)
3. Pull COCO's 'bird' class subset (~3,362 images) as extra background/general-bird diversity
4. Merge all sources into one YOLO-format dataset
5. Fine-tune YOLO11n starting from COCO pretrained weights
6. Validate + run inference on a test image/video
7. Export to NCNN format for fast CPU inference on Raspberry Pi

**Note on the COCO bird subset:** this is general-bird imagery, not pigeon-specific — research on similar systems (Chen et al. 2024, *Sci Rep*) found COCO-pretrained models alone perform poorly on small/distant birds, and used it only as a pretraining base, not as fine-tuning signal for the target species. We include it here for background/negative diversity and general bird-shape reinforcement, not as a substitute for the pigeon-specific datasets.

## 1. Install dependencies

In [ ]:
!pip install ultralytics roboflow pycocotools -q

     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 45.5/45.5 kB 967.1 kB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.4/1.4 MB 35.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 285.0/285.0 kB 29.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 49.9/49.9 MB 19.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.5/1.5 MB 90.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 5.4/5.4 MB 137.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 58.4/58.4 kB 5.1 MB/s eta 0:00:00


## 2. Pull datasets from Roboflow

You need a free Roboflow account + API key: https://app.roboflow.com/settings/api

Paste your key below. **Do not share this notebook publicly with your key still in it** — clear the output cell or use `getpass` before submitting your project.

In [2]:
from getpass import getpass
ROBOFLOW_API_KEY = getpass('Enter your Roboflow API key: ')

Enter your Roboflow API key: ··········


In [3]:
from roboflow import Roboflow
rf = Roboflow(api_key=ROBOFLOW_API_KEY)

# --- Dataset 1: NEA pigeon+foxes detector (Singapore domain match) ---
project_nea = rf.workspace("nea-pn0bc").project("pigeon-foxes-detector")
dataset_nea = project_nea.version(1).download("yolov8", location="/content/data_nea")

# --- Dataset 2: Pigeons Detection (1199 images, single Pigeon class) ---
project_yolo = rf.workspace("yolo-bl12d").project("pigeons-detection-l7u3l")
dataset_yolo = project_yolo.version(1).download("yolov8", location="/content/data_yolo")

print("Downloaded both datasets.")
print("NEA:", dataset_nea.location)
print("YOLO-1199:", dataset_yolo.location)

loading Roboflow workspace...
loading Roboflow project...
Exporting format yolov8 in progress : 12.0%
Version export complete for yolov8 format



Extracting Dataset Version Zip to /content/data_nea in yolov8:: 100%|██████████| 905/905 [00:00<00:00, 8461.08it/s]


Creating new Ultralytics Settings v0.0.7 file ✅ 
View Ultralytics Settings with 'yolo settings' or at '/root/.config/Ultralytics/settings.json'
Update Settings with 'yolo settings key=value', i.e. 'yolo settings runs_dir=path/to/dir'. For help see https://docs.ultralytics.com/quickstart/#ultralytics-settings.
loading Roboflow workspace...
loading Roboflow project...



Extracting Dataset Version Zip to /content/data_yolo in yolov8:: 100%|██████████| 2410/2410 [00:00<00:00, 3769.82it/s]

Downloaded both datasets.
NEA: /content/data_nea
YOLO-1199: /content/data_yolo


**Note on versions/exact IDs:** Roboflow project slugs and version numbers can shift over time. If either `project()` or `version()` call above 404s, go to the dataset page on Roboflow Universe, click **Use this Dataset → YOLOv8**, and it will show you the exact `workspace`, `project`, and `version` values plus ready-to-paste download code. Swap those in here.

- NEA dataset: https://universe.roboflow.com/nea-pn0bc/pigeon-foxes-detector
- 1199-image dataset: https://universe.roboflow.com/yolo-bl12d/pigeons-detection-l7u3l

## 3. Pull COCO's 'bird' class subset

COCO 2017 train/val contains 123,287 images total, of which about 3,362 include birds (of any species — sparrows, crows, ducks, gulls, etc., not pigeon-specific). We use `pycocotools` to download only the annotation index first (small), find which images contain the 'bird' category, then download just those images rather than the full ~19GB COCO dataset.

**Why include this at all if it's not pigeon-specific:** it broadens what 'not a pigeon but still bird-shaped' looks like, and gives the model more general bird silhouette/texture exposure beyond the ~1,600 pigeon images from Roboflow. Treat it as a smaller supplementary slice, not the backbone of your training set.

In [4]:
import os

os.makedirs('/content/coco', exist_ok=True)

# Download only the 2017 val annotations (small, ~1GB zip) rather than the full train annotations (~19GB)
# The val set alone has hundreds of bird images, which is enough for a supplementary slice
!wget -q http://images.cocodataset.org/annotations/annotations_trainval2017.zip -O /content/coco/annotations.zip
!unzip -q /content/coco/annotations.zip -d /content/coco
print("COCO annotations downloaded.")

COCO annotations downloaded.


In [5]:
from pycocotools.coco import COCO
import os

coco = COCO('/content/coco/annotations/instances_val2017.json')

bird_cat_id = coco.getCatIds(catNms=['bird'])[0]
bird_img_ids = coco.getImgIds(catIds=[bird_cat_id])
print(f"Found {len(bird_img_ids)} images containing at least one bird in COCO val2017")

bird_imgs = coco.loadImgs(bird_img_ids)

loading annotations into memory...
Done (t=0.53s)
creating index...
index created!
Found 125 images containing at least one bird in COCO val2017


In [6]:
import os, requests

COCO_IMG_DIR = '/content/coco/bird_images'
os.makedirs(COCO_IMG_DIR, exist_ok=True)

for img in bird_imgs:
    fpath = f"{COCO_IMG_DIR}/{img['file_name']}"
    if os.path.exists(fpath):
        continue
    r = requests.get(img['coco_url'], timeout=10)
    with open(fpath, 'wb') as f:
        f.write(r.content)

print(f"Downloaded {len(os.listdir(COCO_IMG_DIR))} COCO bird images to {COCO_IMG_DIR}")

Downloaded 125 COCO bird images to /content/coco/bird_images


## 4. Convert COCO bird annotations to YOLO format

COCO annotations are `[x_min, y_min, width, height]` in pixel coordinates. YOLO needs `[x_center, y_center, width, height]` normalized to 0-1. This cell converts and writes one `.txt` label file per image, then folds them into the same `merged_dataset` structure used for the Roboflow sets, split 80/10/10 into train/valid/test.

**Note:** these get class index `0` too (pigeon) even though they're general birds — this is intentional here, since the goal is teaching the model 'bird-shaped things in this region are worth flagging,' not species discrimination. If your model ends up over-triggering on non-pigeon birds (crows, mynas) during testing, that's the tradeoff to revisit — you'd want to drop this section or relabel these as a separate 'other_bird' negative class instead.

In [7]:
import random

random.seed(42)
random.shuffle(bird_imgs)

n = len(bird_imgs)
split_train = bird_imgs[:int(n*0.8)]
split_valid = bird_imgs[int(n*0.8):int(n*0.9)]
split_test  = bird_imgs[int(n*0.9):]

coco_splits = {"train": split_train, "valid": split_valid, "test": split_test}
for split_name, imgs in coco_splits.items():
    print(f"COCO {split_name}: {len(imgs)} images")

COCO train: 100 images
COCO valid: 12 images
COCO test: 13 images


In [8]:
import shutil

def convert_and_copy_coco(split_name, imgs):
    count = 0
    for img in imgs:
        src_path = f"{COCO_IMG_DIR}/{img['file_name']}"
        if not os.path.exists(src_path):
            continue  # skip any that failed to download

        ann_ids = coco.getAnnIds(imgIds=img['id'], catIds=[bird_cat_id])
        anns = coco.loadAnns(ann_ids)
        if not anns:
            continue

        img_w, img_h = img['width'], img['height']
        yolo_lines = []
        for ann in anns:
            x_min, y_min, w, h = ann['bbox']
            x_center = (x_min + w / 2) / img_w
            y_center = (y_min + h / 2) / img_h
            w_norm = w / img_w
            h_norm = h / img_h
            yolo_lines.append(f"0 {x_center:.6f} {y_center:.6f} {w_norm:.6f} {h_norm:.6f}")

        new_stem = f"coco_{img['id']}"
        ext = os.path.splitext(img['file_name'])[1]
        shutil.copy(src_path, f"{MERGED_ROOT}/{split_name}/images/{new_stem}{ext}")
        with open(f"{MERGED_ROOT}/{split_name}/labels/{new_stem}.txt", "w") as f:
            f.write("\n".join(yolo_lines) + "\n")
        count += 1

    print(f"[COCO-bird] {split_name}: converted {count} images")

# This function is defined here but called later in section 6, after MERGED_ROOT's
# folder structure has been created — just run all cells in order top-to-bottom.

## 5. Inspect class names before merging

**Important:** the NEA dataset has multiple classes (Pigeon, Fox, Human in some versions). We only want the Pigeon class for this project — check `data.yaml` in each downloaded folder and confirm class indices before merging, since YOLO label files reference classes by index number, not name.

In [9]:
import yaml

for name, path in [("NEA", dataset_nea.location), ("YOLO-1199", dataset_yolo.location)]:
    with open(f"{path}/data.yaml") as f:
        d = yaml.safe_load(f)
    print(name, "-> classes:", d.get('names'))

NEA -> classes: ['Fox', 'pigeon']
YOLO-1199 -> classes: ['Pigeon']


## 6. Merge datasets into a single unified dataset

This script:
- Copies all images from both Roboflow sources into one folder structure
- Remaps every class label to a single class: `0 = pigeon`
- If NEA has extra classes (fox/human), those label lines are **dropped**, not remapped — we don't want the model learning to detect foxes as pigeons
- Keeps the standard YOLO folder layout: `train/images`, `train/labels`, `valid/images`, `valid/labels`, `test/images`, `test/labels`
- Then folds in the COCO bird subset converted above

In [10]:
import os, shutil, yaml

MERGED_ROOT = "/content/merged_dataset"
SPLITS = ["train", "valid", "test"]

for split in SPLITS:
    os.makedirs(f"{MERGED_ROOT}/{split}/images", exist_ok=True)
    os.makedirs(f"{MERGED_ROOT}/{split}/labels", exist_ok=True)

def get_pigeon_class_index(dataset_path):
    """Find which class index corresponds to 'pigeon' (case-insensitive) in this dataset's data.yaml"""
    with open(f"{dataset_path}/data.yaml") as f:
        d = yaml.safe_load(f)
    names = d['names']
    for i, n in enumerate(names):
        if 'pigeon' in n.lower():
            return i
    raise ValueError(f"No pigeon class found in {dataset_path}, classes were: {names}")

def merge_dataset(dataset_path, source_tag, global_prefix):
    """Copy images+labels from one Roboflow export into the merged dataset,
    remapping the pigeon class to 0 and dropping all other classes."""
    pigeon_idx = get_pigeon_class_index(dataset_path)
    print(f"[{source_tag}] pigeon class index = {pigeon_idx}")

    counts = {"train": 0, "valid": 0, "test": 0}

    for split in SPLITS:
        img_dir = f"{dataset_path}/{split}/images"
        lbl_dir = f"{dataset_path}/{split}/labels"
        if not os.path.isdir(img_dir):
            continue  # some exports don't have a test split

        for fname in os.listdir(img_dir):
            stem, ext = os.path.splitext(fname)
            label_path = f"{lbl_dir}/{stem}.txt"
            if not os.path.exists(label_path):
                continue

            # Read and remap labels, dropping non-pigeon classes
            with open(label_path) as f:
                lines = f.readlines()

            kept_lines = []
            for line in lines:
                parts = line.strip().split()
                if not parts:
                    continue
                cls_idx = int(parts[0])
                if cls_idx == pigeon_idx:
                    kept_lines.append("0 " + " ".join(parts[1:]))

            if not kept_lines:
                continue  # skip images with no pigeon annotations after filtering

            new_stem = f"{global_prefix}_{stem}"
            shutil.copy(f"{img_dir}/{fname}", f"{MERGED_ROOT}/{split}/images/{new_stem}{ext}")
            with open(f"{MERGED_ROOT}/{split}/labels/{new_stem}.txt", "w") as f:
                f.write("\n".join(kept_lines) + "\n")

            counts[split] += 1

    print(f"[{source_tag}] merged counts: {counts}")

merge_dataset(dataset_nea.location, "NEA", "nea")
merge_dataset(dataset_yolo.location, "YOLO1199", "y1199")

# Now that MERGED_ROOT's folders exist, convert + copy in the COCO bird subset from section 4
for split_name, imgs in coco_splits.items():
    convert_and_copy_coco(split_name, imgs)

[NEA] pigeon class index = 1
[NEA] merged counts: {'train': 126, 'valid': 40, 'test': 24}
[YOLO1199] pigeon class index = 0
[YOLO1199] merged counts: {'train': 895, 'valid': 241, 'test': 63}
[COCO-bird] train: converted 100 images
[COCO-bird] valid: converted 12 images
[COCO-bird] test: converted 13 images


In [11]:
# Sanity check: count final images per split (Roboflow pigeon + COCO bird combined)
for split in SPLITS:
    n_img = len(os.listdir(f"{MERGED_ROOT}/{split}/images"))
    n_lbl = len(os.listdir(f"{MERGED_ROOT}/{split}/labels"))
    print(f"{split}: {n_img} images, {n_lbl} label files")

train: 1121 images, 1121 label files
valid: 293 images, 293 label files
test: 100 images, 100 label files


In [12]:
# Write the merged data.yaml for YOLO training
merged_yaml = {
    'train': f'{MERGED_ROOT}/train/images',
    'val': f'{MERGED_ROOT}/valid/images',
    'test': f'{MERGED_ROOT}/test/images',
    'nc': 1,
    'names': ['pigeon']
}

with open(f'{MERGED_ROOT}/data.yaml', 'w') as f:
    yaml.dump(merged_yaml, f)

print(open(f'{MERGED_ROOT}/data.yaml').read())

names:
- pigeon
nc: 1
test: /content/merged_dataset/test/images
train: /content/merged_dataset/train/images
val: /content/merged_dataset/valid/images



## 7. (Optional) Add your own real-world footage

Once you've extracted + labeled frames from your actual camera footage (see earlier discussion — extract at ~1 frame/1-2 sec via ffmpeg/OpenCV, label with Roboflow/CVAT/LabelImg), drop them into the merged dataset the same way:

```python
# Example: after labeling, copy your own frames into train/images + train/labels
# following the same naming convention as above, e.g. prefix 'ownfootage_'
```

Mixing in even 50-100 real labeled frames from your deployment site disproportionately helps real-world accuracy — see earlier discussion on domain shift.

## 8. Fine-tune YOLO11n starting from COCO pretrained weights

`yolo11n.pt` is pretrained on COCO (which already includes a 'bird' class), so it already has useful low/mid-level features for bird shapes — we're fine-tuning, not training from scratch.

In [13]:
from ultralytics import YOLO

model = YOLO('yolo11n.pt')  # nano — fast, good for a real-time deterrent system on Pi CPU

results = model.train(
    data=f'{MERGED_ROOT}/data.yaml',
    epochs=50,
    imgsz=640,
    batch=16,
    patience=10,       # early stop if val performance plateaus
    project='pigeon_detector',
    name='v1',
    device=0            # GPU — make sure Colab runtime is set to GPU (Runtime > Change runtime type)
)

Ultralytics 8.4.117 🚀 Python-3.12.13 torch-2.11.0+cu128 CUDA:0 (Tesla T4, 14913MiB)
engine/trainer: agnostic_nms=False, amp=True, angle=1.0, augment=False, auto_augment=randaugment, batch=16, bgr=0.0, box=7.5, cache=False, cfg=None, channels_last=False, classes=None, close_mosaic=10, cls=0.5, cls_pw=0.0, cls_remap=True, compile=False, conf=None, copy_paste=0.0, copy_paste_mode=flip, cos_lr=False, cutmix=0.0, data=/content/merged_dataset/data.yaml, degrees=0.0, deterministic=True, device=0, dfl=1.5, dgrad=0.5, dis=6.0, distill_model=None, dlam=1.0, dlog=1.0, dnn=False, dropout=0.0, dynamic=False, embed=None, end2end=None, epochs=50, erasing=0.4, exist_ok=False, fliplr=0.5, flipud=0.0, format=torchscript, fraction=1.0, freeze=None, hsv_h=0.015, hsv_s=0.7, hsv_v=0.4, imgsz=640, iou=0.7, keras=False, kobj=1.0, line_width=None, lr0=0.01, lrf=0.01, mask_ratio=4, max_det=300, mixup=0.0, mode=train, model=yolo11n.pt, momentum=0.937, mosaic=1.0, multi_scale=0.0, name=v1, nbs=64, nms=False, opse

## 9. Validate model performance

In [14]:
metrics = model.val()
print("mAP50:", metrics.box.map50)
print("mAP50-95:", metrics.box.map)
print("Precision:", metrics.box.mp)
print("Recall:", metrics.box.mr)

Ultralytics 8.4.117 🚀 Python-3.12.13 torch-2.11.0+cu128 CUDA:0 (Tesla T4, 14913MiB)
YOLO11n summary (fused): 101 layers, 2,582,347 parameters, 0 gradients, 6.4 GFLOPs
val: Fast image access ✅ (ping: 0.0±0.0 ms, read: 1833.7±323.2 MB/s, size: 57.6 KB)
val: Scanning /content/merged_dataset/valid/labels.cache... 293 images, 0 backgrounds, 0 corrupt: 100% ━━━━━━━━━━━━ 293/293 102.4Mit/s 0.0s
                 Class     Images  Instances      Box(P          R      mAP50  mAP50-95): 100% ━━━━━━━━━━━━ 19/19 2.9it/s 6.5s
                   all        293        596      0.804      0.772      0.835      0.611
Speed: 2.6ms preprocess, 8.5ms inference, 0.0ms loss, 2.4ms postprocess per image
Results saved to /content/runs/detect/val
mAP50: 0.8351219720593465
mAP50-95: 0.6105092241634449
Precision: 0.8041768391238369
Recall: 0.7718120805369127


## 10. Run inference on a test image or video

Upload a test image/video via the Colab file browser (left sidebar) first, or mount Google Drive.

In [17]:
# Single image test
#results = model.predict(source='/content/test_image.jpg', save=True, conf=0.4)

# For a video feed (what you'll actually deploy):
results = model.predict(source='/content/15068-260649470.mp4', save=True, conf=0.4)

# For a live webcam feed in a local/deployed setting (won't work directly in Colab):
# results = model.predict(source=0, show=True, conf=0.4)  # 0 = default camera


WARNING ⚠️ 
Inference results will accumulate in RAM unless `stream=True` is passed, which can cause out-of-memory errors for large
sources or long-running streams and videos. See https://docs.ultralytics.com/modes/predict/ for help.

Example:
    results = model(source=..., stream=True)  # generator of Results objects
    for r in results:
        boxes = r.boxes  # Boxes object for bbox outputs
        masks = r.masks  # Masks object for segment masks outputs
        probs = r.probs  # Class probabilities for classification outputs

video 1/1 (frame 1/694) /content/15068-260649470.mp4: 384x640 (no detections), 8.2ms
video 1/1 (frame 2/694) /content/15068-260649470.mp4: 384x640 (no detections), 11.9ms
video 1/1 (frame 3/694) /content/15068-260649470.mp4: 384x640 (no detections), 10.3ms
video 1/1 (frame 4/694) /content/15068-260649470.mp4: 384x640 (no detections), 9.4ms
video 1/1 (frame 5/694) /content/15068-260649470.mp4: 384x640 (no detections), 11.2ms
video 1/1 (frame 6/694) /conte

KeyboardInterrupt: 

In [18]:
import cv2
from IPython.display import Video, display
import os

video_path = '/content/15068-260649470.mp4'  # confirm this matches your actual filename

assert os.path.exists(video_path), f"File not found: {video_path}"

# Run detection, save annotated video with bounding boxes drawn
results = model.predict(source=video_path, save=True, conf=0.4)

# Find where Ultralytics saved the annotated output
save_dir = results[0].save_dir
output_path = os.path.join(save_dir, os.path.basename(video_path))
print("Annotated video saved to:", output_path)


WARNING ⚠️ 
Inference results will accumulate in RAM unless `stream=True` is passed, which can cause out-of-memory errors for large
sources or long-running streams and videos. See https://docs.ultralytics.com/modes/predict/ for help.

Example:
    results = model(source=..., stream=True)  # generator of Results objects
    for r in results:
        boxes = r.boxes  # Boxes object for bbox outputs
        masks = r.masks  # Masks object for segment masks outputs
        probs = r.probs  # Class probabilities for classification outputs

video 1/1 (frame 1/694) /content/15068-260649470.mp4: 384x640 (no detections), 11.1ms
video 1/1 (frame 2/694) /content/15068-260649470.mp4: 384x640 (no detections), 15.6ms
video 1/1 (frame 3/694) /content/15068-260649470.mp4: 384x640 (no detections), 19.4ms
video 1/1 (frame 4/694) /content/15068-260649470.mp4: 384x640 (no detections), 19.4ms
video 1/1 (frame 5/694) /content/15068-260649470.mp4: 384x640 (no detections), 20.8ms
video 1/1 (frame 6/694) /con

In [24]:
import os

save_dir = results[0].save_dir
output_path = os.path.join(save_dir, '15068-260649470.avi')  # matches actual saved filename
print("Exists:", os.path.exists(output_path))

!ffmpeg -y -i "{output_path}" -vcodec libx264 -f mp4 /content/output_playable.mp4

from IPython.display import Video
Video('/content/output_playable.mp4', embed=True, width=640)

Exists: True
ffmpeg version 4.4.2-0ubuntu0.22.04.1 Copyright (c) 2000-2021 the FFmpeg developers
  built with gcc 11 (Ubuntu 11.2.0-19ubuntu1)
  configuration: --prefix=/usr --extra-version=0ubuntu0.22.04.1 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --enable-gnutls --enable-ladspa --enable-libaom --enable-libass --enable-libbluray --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libgme --enable-libgsm --enable-libjack --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-libpulse --enable-librabbitmq --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libsrt --enable-libssh --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-

## 11. Export weights for deployment

Download `best.pt` from `pigeon_detector/v1/weights/` — this is the file you'll load in your actual deterrent system script (the one that also triggers the laser/ultrasonic output on detection).

In [ ]:
from google.colab import files
files.download('pigeon_detector/v1/weights/best.pt')

## 12. Export to NCNN for Raspberry Pi deployment

Plain PyTorch (`.pt`) inference is slow on a Pi's CPU (no GPU to lean on). **NCNN** is a format optimized for ARM CPUs and typically gives a large speed-up over raw PyTorch on a Pi — this is the format you actually want to run on the deterrent unit itself.

This export step should be run **on the Pi** (or at least matching Python/Ultralytics versions), since NCNN export can be architecture-sensitive. If exporting here in Colab works fine, download the resulting folder; if you hit issues, install `ultralytics` on the Pi directly and re-run just this export line there using your downloaded `best.pt`.

In [ ]:
model.export(format='ncnn', imgsz=640)  # produces a 'best_ncnn_model' folder

# On the Pi, load it like this instead of the .pt file:
#   from ultralytics import YOLO
#   pi_model = YOLO('best_ncnn_model')
#   results = pi_model.predict(source=0, conf=0.4)  # 0 = Pi camera

**If your group ends up using a Coral USB Accelerator instead of/alongside the Pi CPU**, you'd export to TFLite with INT8 quantization instead:

```python
model.export(format='tflite', int8=True, data=f'{MERGED_ROOT}/data.yaml', imgsz=640)
```

This needs a calibration pass over your dataset (hence passing `data=`), which is why it's slower to export than NCNN but gives you Coral-compatible weights. Only do this once hardware is confirmed — no need to block on it now.